# Explore how various datasets are geographically related and how to best link various datasets

## Start with visualizing the snapped points (created from running snap_features.slurm)

In [1]:
import geopandas as gpd

snapped_path = "../data/processed/snapped_features_19020401.gpkg"

print(gpd.list_layers(snapped_path))

for layer in gpd.list_layers(snapped_path)["name"]:
    gdf = gpd.read_file(snapped_path, layer=layer)
    print(f"\n{layer}: {len(gdf)} features")
    print("CRS:", gdf.crs)

                name geometry_type
0       dams_snapped         Point
1   stations_snapped         Point
2  stations_original         Point
3      dams_original         Point

dams_snapped: 3 features
CRS: EPSG:4326

stations_snapped: 782 features
CRS: EPSG:4326

stations_original: 391 features
CRS: EPSG:4326

dams_original: 1 features
CRS: EPSG:4326


In [4]:
import pandas as pd
import geopandas as gpd
import folium
from folium.plugins import MarkerCluster

# --------------------------------------------------
# 1. File paths
# --------------------------------------------------
huc8 = "19020401"

wbd_path = "../data/raw/wbd/WBD_National_GPKG.gpkg"
streams_path = "../data/processed/nhdplus_extracted/NHDPLUS_H_19020401_HU8_GDB/NHDPLUS_H_19020401_HU8_GDB.gdb"
snapped_path = f"../data/processed/snapped_features_{huc8}.gpkg"

# --------------------------------------------------
# 2. Load watershed
# --------------------------------------------------
layers = gpd.list_layers(wbd_path)
huc8_layer = layers.loc[
    layers["name"].str.contains("hu8", case=False), "name"
].iloc[0]

wbd = gpd.read_file(wbd_path, layer=huc8_layer)

huc_col = next(
    col for col in wbd.columns
    if col.lower() == "huc8"
)

watershed = wbd[
    wbd[huc_col].astype(str).str.zfill(8) == huc8
].copy()

if watershed.empty:
    raise ValueError(f"Could not find HUC8 {huc8} in {huc8_layer}")

watershed_wgs84 = watershed.to_crs("EPSG:4326")

print("Watershed bounds (longitude/latitude):", watershed_wgs84.total_bounds)
print("Estimated UTM CRS:", watershed_wgs84.estimate_utm_crs())

# --------------------------------------------------
# 3. Load stream network
# --------------------------------------------------
stream_layers = gpd.list_layers(streams_path)
streams = gpd.read_file(streams_path, layer="NHDFlowline")

# Clip to the selected watershed.
streams_wgs84 = streams.to_crs("EPSG:4326")
streams_wgs84 = gpd.clip(streams_wgs84, watershed_wgs84)

print("Stream reaches in watershed:", len(streams_wgs84))

# --------------------------------------------------
# 4. Load snapped features
# --------------------------------------------------
snapped_layers = gpd.list_layers(snapped_path)
print("Snapped layers:", snapped_layers["name"].tolist())

stations_layer = next(
    name for name in snapped_layers["name"]
    if "station" in name.lower()
)
dams_layer = next(
    name for name in snapped_layers["name"]
    if "dam" in name.lower()
)

stations_snapped = gpd.read_file(snapped_path, layer=stations_layer)
dams_snapped = gpd.read_file(snapped_path, layer=dams_layer)

# Ensure all layers use longitude/latitude for Folium.
stations_snapped_wgs84 = stations_snapped.to_crs("EPSG:4326")
dams_snapped_wgs84 = dams_snapped.to_crs("EPSG:4326")

# --------------------------------------------------
# 5. Build map
# --------------------------------------------------
center = watershed_wgs84.geometry.union_all().centroid

m = folium.Map(
    location=[center.y, center.x],
    zoom_start=10,
    tiles="OpenStreetMap",
)

# Convert datetime columns to strings for JSON serialization.
watershed_map = watershed_wgs84.copy()

for col in watershed_map.columns:
    if gpd.pd.api.types.is_datetime64_any_dtype(watershed_map[col]):
        watershed_map[col] = watershed_map[col].astype(str)

folium.GeoJson(
    watershed_map,
    name="HUC8 watershed",
    style_function=lambda feature: {
        "color": "black",
        "weight": 2,
        "fillOpacity": 0.03,
    },
).add_to(m)

# Convert datetime columns to strings for JSON serialization.
streams_map = streams_wgs84.copy()

for col in streams_map.columns:
    if pd.api.types.is_datetime64_any_dtype(streams_map[col]):
        streams_map[col] = streams_map[col].astype(str)

folium.GeoJson(
    streams_map,
    name="NHDFlowline streams",
    style_function=lambda feature: {
        "color": "blue",
        "weight": 1,
        "opacity": 0.6,
    },
).add_to(m)

# Water-quality stations.
print(f"There are {stations_snapped_wgs84.shape[0]} water quality stations")
station_group = folium.FeatureGroup(
    name="Snapped water-quality stations"
)

for _, row in stations_snapped_wgs84.iterrows():
    point = row.geometry

    if point is None or point.is_empty:
        continue

    distance = row.get("snap_distance_m")
    reach_id = row.get("NHDPlusID", "Unknown")
    station_id = row.get("MonitoringLocationIdentifier", "Unknown")

    folium.CircleMarker(
        location=[point.y, point.x],
        radius=3,
        color="darkgreen",
        fill=True,
        fill_color="darkgreen",
        fill_opacity=0.8,
        weight=1,
        popup=(
            f"Station: {station_id}<br>"
            f"Reach ID: {reach_id}<br>"
            f"Snap distance: {distance} m"
        ),
    ).add_to(station_group)

station_group.add_to(m)

# Dam removals.
dam_group = folium.FeatureGroup(name="Snapped dam removals")

for _, row in dams_snapped_wgs84.iterrows():
    point = row.geometry
    if point is None or point.is_empty:
        continue

    folium.Marker(
        location=[point.y, point.x],
        tooltip="Dam removal",
        popup=(
            f"Reach ID: {row.get('NHDPlusID', 'Unknown')}<br>"
            f"Snap distance: {row.get('snap_distance_m', 'Unknown')} m"
        ),
        icon=folium.Icon(color="black", icon="flag"),
    ).add_to(dam_group)

dam_group.add_to(m)

folium.LayerControl(collapsed=False).add_to(m)

m

Watershed bounds (longitude/latitude): [-150.30489042   60.99748548 -148.79631815   61.76083201]
Estimated UTM CRS: EPSG:32606


/home/creighton.jo/.conda/envs/dam-removal/lib/python3.11/site-packages/pyogrio/core.py:169: UserWarning: Measured (M) geometry types are not supported. Original type 'Measured 3D MultiLineString' is converted to 'MultiLineString Z'
  return ogr_list_layers(get_vsi_path_or_buffer(path_or_buffer))
/home/creighton.jo/.conda/envs/dam-removal/lib/python3.11/site-packages/pyogrio/raw.py:200: UserWarning: Measured (M) geometry types are not supported. Original type 'Measured 3D MultiLineString' is converted to 'MultiLineString Z'
  return ogr_read(


Stream reaches in watershed: 4954
Snapped layers: ['stations_original', 'dams_original', 'stations_snapped', 'dams_snapped']
There are 391 water quality stations


## Now examine the tables themselves:

In [3]:
# Stations
stations_snapped.head()

,OrganizationIdentifier,OrganizationFormalName,MonitoringLocationIdentifier,MonitoringLocationName,MonitoringLocationTypeName,MonitoringLocationDescriptionText,HUCEightDigitCode,DrainageAreaMeasure/MeasureValue,DrainageAreaMeasure/MeasureUnitCode,ContributingDrainageAreaMeasure/MeasureValue,...,source_huc8,NHDPlusID,snap_distance_m,original_x,original_y,snap_fraction,snapped_x,snapped_y,feature_id,geometry
0,USGS-AK,USGS Alaska Water Science Center,USGS-15272970,L SURVIVAL C NR ANCHORAGE AK,Stream,NaN,19020401,NaN,NaN,NaN,...,19020401,7.500010e+13,17.116171,348868.567752,6.773509e+06,0.302300,348852.271117,6.773504e+06,USGS-15272970,POINT (-149.8008 61.06722)
1,USGS-AK,USGS Alaska Water Science Center,USGS-15273020,RABBIT C AT HILLSIDE DR NR ANCHORAGE AK,Stream,NaN,19020401,9.85,sq mi,NaN,...,19020401,7.500010e+13,7.968422,352647.591278,6.776664e+06,0.977877,352655.260191,6.776666e+06,USGS-15273020,POINT (-149.7333 61.09695)
2,USGS-AK,USGS Alaska Water Science Center,USGS-15273030,RABBIT C AT E 140 AVE NR ANCHORAGE AK,Stream,NaN,19020401,11.32,sq mi,NaN,...,19020401,7.500010e+13,13.624231,349610.681129,6.776482e+06,0.515974,349597.615445,6.776486e+06,USGS-15273030,POINT (-149.78941 61.09417)
3,USGS-AK,USGS Alaska Water Science Center,USGS-15273040,RABBIT C AT PORCUPINE TRAIL RD NR ANCHORAGE AK,Stream,NaN,19020401,13.30,sq mi,NaN,...,19020401,7.500010e+13,27.595394,347899.375250,6.775750e+06,0.138479,347877.476371,6.775767e+06,USGS-15273040,POINT (-149.82053 61.08695)
4,USGS-AK,USGS Alaska Water Science Center,USGS-15273045,RABBIT C AT OLD SEWARD HWY NR ANCHORAGE AK,Stream,NaN,19020401,13.70,sq mi,NaN,...,19020401,7.500010e+13,3.819037,347598.863889,6.775391e+06,0.464142,347595.756249,6.775393e+06,USGS-15273045,POINT (-149.8258 61.08361)


In [4]:
# Dams
dams_snapped.head()

,AR_ID,NABI_ID,NID_ID,Dam_Name,Year_Removed,Latitude,Longitude,City_County,River,HUC8,...,Last_Updated,NHDPlusID,snap_distance_m,original_x,original_y,snap_fraction,snapped_x,snapped_y,feature_id,geometry
0,AK-010,AK91785,AK00093,Lower Eklutna River Dam,2017,61.449393,-149.32388,Anchorage,Eklutna,Anchorage,...,2/10/2026,7.500010e+13,227.764842,376109.024988,6.815052e+06,0.521747,375882.093582,6.815032e+06,Lower Eklutna River Dam,POINT (-149.32388 61.44939)
1,AK-010,AK91785,AK00093,Lower Eklutna River Dam,2017,61.449393,-149.32388,Anchorage,Eklutna,Anchorage,...,2/10/2026,7.500010e+13,227.764842,376109.024988,6.815052e+06,0.521747,375882.093582,6.815032e+06,Lower Eklutna River Dam,POINT (-149.32388 61.44939)
2,AK-010,AK91785,AK00093,Lower Eklutna River Dam,2017,61.449393,-149.32388,Anchorage,Eklutna,Anchorage,...,2/10/2026,7.500010e+13,227.764842,376109.024988,6.815052e+06,0.521747,375882.093582,6.815032e+06,Lower Eklutna River Dam,POINT (-149.32812 61.44915)


In [5]:
# Print stream fields
streams = gpd.read_file(streams_path, layer="NHDFlowline")
print(", ".join([col for col in streams.columns]))

Permanent_Identifier, FDate, Resolution, GNIS_ID, GNIS_Name, LengthKM, ReachCode, FlowDir, WBArea_Permanent_Identifier, FType, FCode, MainPath, InNetwork, VisibilityFilter, Shape_Length, NHDPlusID, VPUID, Enabled, geometry


/home/creighton.jo/.conda/envs/dam-removal/lib/python3.11/site-packages/pyogrio/raw.py:200: UserWarning: Measured (M) geometry types are not supported. Original type 'Measured 3D MultiLineString' is converted to 'MultiLineString Z'
  return ogr_read(


In [6]:
# Now examine other stream layersn for flow:
import fiona
layers = fiona.listlayers(streams_path)
for layer in layers:
    if "flow" in layer.lower():
        print(layer)

NHDPlusFlow
NHDPlusFlowlineVAA
NHDFlowline


In [7]:
flow = gpd.read_file(
    streams_path,
    layer="NHDPlusFlow",
)

print(", ".join(flow.columns.tolist()))
flow.head()

FromNHDPID, ToNHDPID, NodeNumber, DeltaLevel, Direction, GapDistKm, HasGeo, FromVPUID, ToVPUID, FromPermID, ToPermID


,FromNHDPID,ToNHDPID,NodeNumber,DeltaLevel,Direction,GapDistKm,HasGeo,FromVPUID,ToVPUID,FromPermID,ToPermID
0,7.500010e+13,7.500010e+13,7.500010e+13,0,709,0.0,1,19020401,19020401,{64CBB14B-5F81-4EFD-8A32-4CD741759271},{4E505B91-6426-45EA-BF53-B09E0042F40F}
1,7.500010e+13,7.500010e+13,7.500010e+13,0,709,0.0,1,19020401,19020401,{031ab1f6-c5be-42ca-abed-e5b8ee2722c5},{4dfe71c9-8a4c-4e80-9437-360985d9b211}
2,7.500010e+13,7.500010e+13,7.500010e+13,0,709,0.0,1,19020401,19020401,{0278f7bf-b998-47c2-bdfc-ac006a47b694},{b5c4178f-912c-49bf-92cf-87cbcf7191dc}
3,7.500010e+13,7.500010e+13,7.500010e+13,0,709,0.0,1,19020401,19020401,41714615,{0278f7bf-b998-47c2-bdfc-ac006a47b694}
4,7.500010e+13,7.500010e+13,7.500010e+13,0,709,0.0,1,19020401,19020401,{3f20aad6-c47b-4c05-9670-4bd0d134dce6},41714621


It seems like NHDPlusFlow contains the data we need to construct the network (ie, "FromNHDPID", "ToNHDPID", and "NodeNumber"). However, quick examination of the head of the table displays node IDs as floats in scientific notation. Next, we will convert these IDs to 

In [8]:
print(flow[["FromNHDPID", "ToNHDPID", "NodeNumber"]].iloc[0].to_dict())

print("Direction values:")
print(flow["Direction"].value_counts(dropna=False).head(20))

print("NHDPlusID examples:")
print(streams["NHDPlusID"].head(10).to_list())

{'FromNHDPID': 75000100003238.0, 'ToNHDPID': 75000100002640.0, 'NodeNumber': 75000100000110.0}
Direction values:
Direction
709    4935
712    1866
714     159
Name: count, dtype: int64
NHDPlusID examples:
[75000100000142.0, 75000100000143.0, 75000100000144.0, 75000100000145.0, 75000100000146.0, 75000100000252.0, 75000100000253.0, 75000100000254.0, 75000100000255.0, 75000100000256.0]


In [9]:
stream_ids = set(streams["NHDPlusID"].dropna().astype("int64"))

from_ids = flow["FromNHDPID"].dropna().astype("int64")
to_ids = flow["ToNHDPID"].dropna().astype("int64")

print("Unique stream IDs:", len(stream_ids))
print("From IDs matching streams:", from_ids.isin(stream_ids).sum(), "/", len(from_ids))
print("To IDs matching streams:", to_ids.isin(stream_ids).sum(), "/", len(to_ids))

Unique stream IDs: 4955
From IDs matching streams: 5089 / 6960
To IDs matching streams: 6959 / 6960
